# Ajuste de zonas

El objetivo de este análisis es ajustar la zonificación de Montevideo para que los polígonos tengan una cobertura adecuada de datos de Kido Dynamics. 

La regla principal es que cada polígono contenga al menos 15 antenas. Cuando un polígono tiene menos de 15, se combina con un polígono vecino, siempre que ambos pertenezcan a la misma sección censal.

In [51]:
import geopandas as gpd
import pandas as pd
import folium

## Identificar zonas con menos de 15 antenas

Para el análisis se utilizan tres fuentes de datos:

- **Archivo de puntos brindado por Kido Dynamics:** utilizados para contar la cantidad de antenas dentro de cada polígono.
- **Zonificación:** polígonos que serán ajustados.
- **Secciones censales:** utilizadas para restringir las combinaciones de polígonos a una misma sección censal.

Todos los datos espaciales se proyectan a EPSG:32721 para trabajar con distancias y áreas en metros.

In [ ]:
points = gpd.read_file("../data/montevideo_clip.geojson")
zonificacion = gpd.read_file("../data/zonas-montevideo-actualizadas.gpkg")
secciones_censales = secciones_censales = gpd.read_file("../data/sc_23_pg.gpkg")

In [ ]:
min_antenas = 15

zones = zonificacion.copy().reset_index(drop=True)
pts = points.copy()

if zones.crs != pts.crs:
    pts = pts.to_crs(zones.crs)

# Conteo de antenas por zona
join = gpd.sjoin(pts[['geometry']], zones[['poligono_id', 'geometry']], how='inner', predicate='within')
counts = join.groupby('poligono_id').size().rename('n_antenas')
zones = zones.merge(counts, on='poligono_id', how='left')
zones['n_antenas'] = zones['n_antenas'].fillna(0).astype(int)

# ignoro zonas sin antenas
zones['estado'] = 'sin_antenas_ignorar'
zones.loc[zones['n_antenas'] > 0, 'estado'] = '>=15'
zones.loc[(zones['n_antenas'] > 0) & (zones['n_antenas'] < min_antenas), 'estado'] = '<15'

n_ignorar = int((zones['estado'] == 'sin_antenas_ignorar').sum())
n_low = int((zones['estado'] == '<15').sum())
n_ok = int((zones['estado'] == '>=15').sum())

print(f'Zonas sin antenas (ignorar): {n_ignorar}')
print(f'Zonas con < 15 antenas: {n_low}')
print(f'Zonas con >= 15 antenas: {n_ok}')

# Mapa de diagnostico
m_diag = zones.explore(
    column='estado',
    categorical=True,
    cmap=['#d73027', '#1a9850', '#bdbdbd'],
    tooltip=['poligono_id', 'n_antenas', 'estado'],
    legend=True,
    style_kwds={'weight': 0.8, 'fillOpacity': 0.65}
)

m_diag

## Algoritmo 

A partir de las zonas identificadas en el paso anterior, se aplica un proceso iterativo para combinar aquellas que tienen menos de 15 antenas.

Las combinaciones se realizan únicamente entre zonas que pertenecen a la misma sección censal y que comparten un límite. Se prioriza el vecino que permite alcanzar las 15 antenas con la menor cantidad total de antenas.

Una vez finalizado el proceso, las zonas sin antenas se reincorporan sin modificaciones y se genera un mapa con la zonificación resultante.

In [ ]:
CRS_METROS=32721
MIN_ANTENAS=15

points = gpd.read_file("../data/montevideo_clip.geojson")
zonificacion = gpd.read_file("../data/zonas-montevideo-actualizadas.gpkg")
secciones_censales = gpd.read_file("../data/sc_23_pg.gpkg")

zones = zonificacion.to_crs(epsg=CRS_METROS).copy()
pts =points.to_crs(epsg=CRS_METROS).copy()
secciones=secciones_censales.to_crs(epsg=CRS_METROS).copy()

# CONTAR ANTENAS
join=gpd.sjoin(pts[["geometry"]],zones[["poligono_id","geometry"]],how="inner",predicate="within")
counts=join.groupby("poligono_id").size().rename("n_antenas")
zones=zones.merge(counts,on="poligono_id",how="left")
zones["n_antenas"]=zones["n_antenas"].fillna(0).astype(int)

poligonos_sin_antenas=[556, 455, 552] # estos polígonos se consideran sin antenas, ya que las que tienen asignadas caen en el borde.
zones.loc[zones["poligono_id"].isin(poligonos_sin_antenas),"n_antenas"]=0

# SECCION TEMPORAL PARA EL ALGORITMO
centroides=zones[["poligono_id","geometry"]].copy()
centroides["geometry"]=centroides.geometry.centroid
sec_join=gpd.sjoin(centroides,secciones[["DEPTO","CODSECC","geometry"]],how="left",predicate="within").drop_duplicates("poligono_id")
zones=zones.merge(sec_join[["poligono_id","DEPTO","CODSECC"]],on="poligono_id",how="left")
zones["_seccion_alg"]=zones["DEPTO"].astype(str)+"_"+zones["CODSECC"].astype(str)

print(f"Total de zonas: {len(zones)}")
print(f"Zonas sin antenas: {(zones['n_antenas']==0).sum()}")
print(f"Zonas con 1-14 antenas: {((zones['n_antenas']>0)&(zones['n_antenas']<MIN_ANTENAS)).sum()}")
print(f"Zonas con >=15 antenas: {(zones['n_antenas']>=MIN_ANTENAS).sum()}")

# ALGORITMO
work=zones[zones["n_antenas"]>0].copy()
work["ids_originales"]=work["poligono_id"].astype(str)

def borde_compartido(geom1,geom2):
    return geom1.boundary.intersection(geom2.boundary).length

while True:
    zonas_bajas=work[work["n_antenas"]<MIN_ANTENAS]
    if len(zonas_bajas)==0:
        break
    progreso=False
    for idx in zonas_bajas.index:
        if idx not in work.index:
            continue
        zona=work.loc[idx]
        posibles=work.sindex.query(zona.geometry,predicate="touches")
        vecinos=work.iloc[posibles].copy()
        vecinos=vecinos[(vecinos.index!=idx)&(vecinos["_seccion_alg"]==zona["_seccion_alg"])]
        if len(vecinos)==0:
            continue
        vecinos["borde_compartido"]=vecinos.geometry.apply(lambda g:borde_compartido(zona.geometry,g))
        vecinos=vecinos[vecinos["borde_compartido"]>0]
        if len(vecinos)==0:
            continue
        vecinos["total"]= zona["n_antenas"]+vecinos["n_antenas"]
        llegan = vecinos[vecinos["total"]>=MIN_ANTENAS]
        if len(llegan)>0:
            vecino_idx=llegan.sort_values(["total","borde_compartido"],ascending=[True,False]).index[0]
        else:
            vecino_idx=vecinos.sort_values(["n_antenas","borde_compartido"],ascending=[False,False]).index[0]
        vecino= work.loc[vecino_idx]
        work.loc[idx,"geometry"]=zona.geometry.union(vecino.geometry)
        work.loc[idx,"n_antenas"]=zona["n_antenas"]+vecino["n_antenas"]
        work.loc[idx,"ids_originales"]=str(zona["ids_originales"])+","+str(vecino["ids_originales"])
        work=work.drop(index=vecino_idx)
        progreso = True
        break
    if not progreso:
        break

# AGREGAR NUEVAMENTE LAS ZONAS SIN ANTENAS
zonas_sin_antenas=zones[zones["n_antenas"]==0].copy()
zonas_sin_antenas["ids_originales"]=zonas_sin_antenas["poligono_id"].astype(str)

resultado=pd.concat([zonas_sin_antenas,work],ignore_index=True)
resultado=gpd.GeoDataFrame(resultado,geometry="geometry",crs=CRS_METROS)
resultado["tipo_resultado"]="original"
resultado.loc[resultado["ids_originales"].str.contains(","),"tipo_resultado"]="dissolved"

print()
print("==========================================")
print("RESULTADO DEL ALGORITMO")
print("==========================================")
print(f"Zonas finales: {len(resultado)}")
print(f"Zonas disueltas: {(resultado['tipo_resultado']=='dissolved').sum()}")
print(f"Zonas con >=15 antenas: {(resultado['n_antenas']>=MIN_ANTENAS).sum()}")
print(f"Zonas con 1-14 antenas: {((resultado['n_antenas']>0)&(resultado['n_antenas']<MIN_ANTENAS)).sum()}")
print(f"Zonas con 0 antenas: {(resultado['n_antenas']==0).sum()}")

resultado_wgs=resultado.to_crs(epsg=4326)
centro=resultado_wgs.geometry.union_all().centroid
m=folium.Map(location=[centro.y,centro.x],zoom_start=11,tiles="OpenStreetMap")

def estilo_alg(feature):
    n=feature["properties"]["n_antenas"]
    tipo=feature["properties"]["tipo_resultado"]
    if tipo=="dissolved":
        return {"fillColor":"purple","color":"purple","weight":2,"fillOpacity":0.65}
    elif n==0:
        return {"fillColor":"lightgray","color":"gray","weight":0.5,"fillOpacity":0.25}
    elif n<MIN_ANTENAS:
        return {"fillColor":"red","color":"red","weight":2,"fillOpacity":0.65}
    else:
        return {"fillColor":"green","color":"green","weight":1,"fillOpacity":0.45}

folium.GeoJson(
    resultado_wgs,
    style_function=estilo_alg,
    highlight_function=lambda x:{"weight":3,"color":"yellow","fillOpacity":0.8},
    tooltip=folium.GeoJsonTooltip(
        fields=["poligono_id","ids_originales","n_antenas","tipo_resultado"],
        aliases=["ID:","IDs originales:","Antenas:","Resultado:"],
        sticky=False
    )
).add_to(m)

m

Total de zonas: 630
Zonas sin antenas: 158
Zonas con 1-14 antenas: 80
Zonas con >=15 antenas: 392

RESULTADO DEL ALGORITMO
Zonas finales: 570
Zonas disueltas: 58
Zonas con >=15 antenas: 412
Zonas con 1-14 antenas: 0
Zonas con 0 antenas: 158


## 3. Asignación de departamento y sección censal

Una vez finalizado el ajuste de las zonas, se le asigna a cada polígono de la zonificación su departamento y sección censal.

El departamento se determina a partir del centroide de cada polígono. Para la sección censal, se consideran las secciones que intersectan al menos el 1% de la superficie del polígono.

Finalmente, se genera un mapa interactivo con la zonificación ajustada y las secciones censales.

In [64]:
resultado = resultado.drop(columns=["DEPTO","CODSECC","CODSECC_x","CODSECC_y","_seccion_alg","depto_codigo","depto_nombre"],errors="ignore")

# DEPARTAMENTO: uso el centroide
deptos = secciones.dissolve(by="DEPTO",aggfunc="first")[["NOMDEPTO","geometry"]].reset_index()
deptos = deptos.rename(columns={"DEPTO":"depto_codigo", "NOMDEPTO":"depto_nombre"})
centroides = resultado[["poligono_id","geometry"]].copy()
centroides["geometry"]= centroides.geometry.centroid
asignacion_depto = gpd.sjoin(centroides, deptos, how="left", predicate="within").drop_duplicates("poligono_id")
resultado=resultado.merge(asignacion_depto[["poligono_id", "depto_codigo", "depto_nombre"]],on="poligono_id",how="left")
resultado.loc[resultado["poligono_id"]==498,"depto_codigo"]="01"
resultado.loc[resultado["poligono_id"]==498,"depto_nombre"]="MONTEVIDEO"

# SECCION CENSAL: usamos el porcentaje de area compartida
inter=gpd.overlay(resultado[["poligono_id","geometry"]],secciones[["CODSECC","geometry"]],how="intersection",keep_geom_type=False)

def extraer_poligonos(geom):
    if geom.geom_type in ["Polygon","MultiPolygon"]:
        return geom
    if geom.geom_type=="GeometryCollection":
        polys=[g for g in geom.geoms if g.geom_type in ["Polygon","MultiPolygon"]]
        if polys:
            return gpd.GeoSeries(polys).union_all()
    return None

inter["geometry"]=inter.geometry.apply(extraer_poligonos)
inter=inter[inter.geometry.notna()]
inter["area_interseccion"]=inter.geometry.area
areas_zona=resultado[["poligono_id","geometry"]].copy()
areas_zona["area_zona"]= areas_zona.geometry.area
inter=inter.merge(areas_zona[["poligono_id","area_zona"]],on="poligono_id",how="left")
inter["porcentaje"]= inter["area_interseccion"]/inter["area_zona"]
inter = inter[inter["porcentaje"] >= 0.01] # porcentaje 1%
codsecc_por_zona = inter.groupby("poligono_id")["CODSECC"].apply(lambda x:",".join(sorted(set(x.astype(str))))).reset_index()
resultado = resultado.merge(codsecc_por_zona,on="poligono_id",how="left")
resultado = resultado.rename(columns={"CODSECC":"seccion_codigo"})
resultado=resultado.loc[:,~resultado.columns.duplicated()]

# MAPA
resultado_wgs=resultado.to_crs(epsg=4326)
secciones_wgs=secciones.to_crs(epsg=4326)
centro=resultado_wgs.geometry.union_all().centroid
m2=folium.Map(location=[centro.y,centro.x],zoom_start=11,tiles="OpenStreetMap")

folium.GeoJson(secciones_wgs,name = "Secciones censales", style_function=lambda feature:{"fillColor":"transparent","color":"#002244","weight":1,"fillOpacity":0},tooltip=folium.GeoJsonTooltip(fields=["DEPTO","CODSECC"],aliases=["Departamento:","CODSECC:"],sticky=False)).add_to(m2)
folium.GeoJson(resultado_wgs,name = "Zonificación", style_function=lambda feature:{"fillColor":"steelblue","color":"#009FDA","weight":1,"fillOpacity":0.6},highlight_function=lambda x:{"weight":3,"color":"yellow","fillOpacity":0.8},tooltip=folium.GeoJsonTooltip(fields=["poligono_id","tipo_zona","depto_codigo","depto_nombre","seccion_codigo"],aliases=["ID:","Tipo zona:","Código depto:","Departamento:","Sección censal:"],sticky=False)).add_to(m2)

folium.LayerControl().add_to(m2)
m2

In [65]:
resultado = resultado.reset_index(drop=True)
resultado["poligono_id"] = resultado.index
resultado = resultado[["poligono_id","tipo_zona","depto_codigo","depto_nombre", "seccion_codigo", "geometry"]]
resultado.to_file("output/zonificacion-montevideo-final.gpkg", driver="GPKG")